In [5]:
%pip install -q "git+https://github.com/Stability-AI/stable-audio-3.git" soundfile

  Installing build dependencies ... done
  Getting requirements to build wheel ... done
  Preparing metadata (pyproject.toml) ... done
ERROR: pip's dependency resolver does not currently take into account all the packages that are installed. This behaviour is the source of the following dependency conflicts.
torchvision 0.26.0+cpu requires torch==2.11.0, but you have torch 2.7.1 which is incompatible.
numba 0.61.2 requires numpy<2.3,>=1.24, but you have numpy 2.5.4 which is incompatible.


In [8]:
import torch
import soundfile as sf
from pathlib import Path
from huggingface_hub import login
from IPython.display import Audio, display
from stable_audio_3 import StableAudioModel

# Authenticate with Hugging Face if required
login()

device = "cuda" if torch.cuda.is_available() else "cpu"
print("Using device:", device)

model = StableAudioModel.from_pretrained("small-music", device=device)

# Save generated sounds in Google Drive
from google.colab import drive
drive.mount("/content/drive")

OUTPUT_DIR = Path("/content/drive/MyDrive/FictionalAnimals/animal_sounds")
OUTPUT_DIR.mkdir(parents=True, exist_ok=True)

VARIATIONS_PER_PROMPT = 3
DURATION = 21
STEPS = 8
BASE_SEED = 42

Using device: cpu


/usr/local/lib/python3.13/dist-packages/torch/nn/utils/weight_norm.py:144: FutureWarning: `torch.nn.utils.weight_norm` is deprecated in favor of `torch.nn.utils.parametrizations.weight_norm`.
  return module
/usr/local/lib/python3.13/dist-packages/torch/nn/utils/weight_norm.py:144: FutureWarning: `torch.nn.utils.weight_norm` is deprecated in favor of `torch.nn.utils.parametrizations.weight_norm`.
  return module


Loading weights:   0%|          | 0/134 [00:00<?, ?it/s]

Mounted at /content/drive


In [20]:

animal_prompts = [
    {
        "name": "0-jungle-ambient",
        "prompt": "ambient jungle soundscape",
        "duration": 120,
    }
    # {
    #     "name": "1-pirate-dog",
    #     "prompt": "A pirate dog barking, he is a good boy",
    #     "duration": 12,
    # },
    # {
    #     "name": "2-polite-fox",
    #     "prompt": "a polite looking fox doing its sounds, it seems shy",
    #     "duration": 8,
    # },
    # {
    #     "name": "3-reindeer-cat",
    #     "prompt": "A reindeer cat with a red nose and cute eyes",
    #     "duration": 12,
    # },
    # {
    #     "name": "4-ferrari-horse",
    #     "prompt": "A Ferrari horse that neighs and does V12 F1 engine sounds",
    #     "duration": 15,
    # },
    # {
    #     "name": "5-duck-goose",
    #     "prompt": "a goose duck hybrid going increasingly crazy",
    #     "duration": 12,
    # },
    # {
    #     "name": "6-fly-bee",
    #     "prompt": "It buzzes like a fly and does goopy noises from collecting pollen",
    #     "duration": 10,
    # },
    # {
    #     "name": "7-dodge-ram-goat",
    #     "prompt": "Goat blea but it's built tough",
    #     "duration": 15,
    # },
    # {
    #     "name": "8-ouiia-cat",
    #     "prompt": "Its a kitten but it goes ou-i-i-a-i, ou-i-i-i-a, i",
    #     "duration": 12,
    # },
    # {
    #     "name": "9-red-elephant",
    #     "prompt": "does elephant sounds but also like a boiling kettle",
    #     "duration": 8,
    # },
    # {
    #     "name": "10-wolf-dog",
    #     "prompt": "wolf dog hybrid howling",
    #     "duration": 8,
    # },
    # {
    #     "name": "11-purple bunny horse",
    #     "prompt": "a purple bunny horse neighing",
    #     "duration": 12,
    # },
    # {
    #     "name": "12-mouth-breather",
    #     "prompt": "a fish that breathes loudly out its mouth and sounds like it smokes cigarettes",
    #     "duration": 15,
    # },
    # {
    #     "name": "13-leopard-lion",
    #     "prompt": "a leopard lion doing both animal sounds as if its getting angry at something",
    #     "duration": 10,
    # },
    # {
    #     "name": "14-squirrel-raccoon",
    #     "prompt": "a squirrel raccoon looking for nuts",
    #     "duration": 10,
    # },
    # {
    #     "name": "15-koala-panda",
    #     "prompt": "a koala-panda atop a tree eating bamboo",
    #     "duration": 15,
    # },
    # {
    #     "name": "16-starfish-octopus",
    #     "prompt": "a starfish octopus hitting the sand underwater",
    #     "duration": 12,
    # },
]

VARIATIONS_PER_PROMPT = 3
STEPS = 8
BASE_SEED = 42

assert len(animal_prompts) == 1
assert all(p["duration"] > 0 for p in animal_prompts)

print(f"{len(animal_prompts)} prompts × {VARIATIONS_PER_PROMPT} "
      f"variations = {len(animal_prompts) * VARIATIONS_PER_PROMPT} clips")


1 prompts × 3 variations = 3 clips


In [16]:
def unpack(out, default_sr=44100):
    if isinstance(out, (tuple, list)) and len(out) == 2:
        a, b = out
        if isinstance(a, int):
            return b, a
        if isinstance(b, int):
            return a, b
    return out, default_sr


def save_audio_batch(out, output_folder, filename_prefix):
    audio, sr = unpack(out)
    audio = torch.as_tensor(audio).float().detach().cpu()

    # Make shape (batch, channels, samples)
    if audio.dim() == 1:
        audio = audio.unsqueeze(0).unsqueeze(0)
    elif audio.dim() == 2:
        audio = audio.unsqueeze(0)

    output_folder = Path(output_folder)
    output_folder.mkdir(parents=True, exist_ok=True)

    saved_paths = []

    for i, clip in enumerate(audio):
        clip = clip / clip.abs().max().clamp(min=1e-8)

        path = output_folder / f"{filename_prefix}_variation_{i + 1:02d}.wav"

        # Convert (channels, samples) to (samples, channels) for soundfile
        sf.write(path, clip.T.numpy(), sr)

        saved_paths.append(path)
        print(f"Saved: {path.name} — {clip.shape[-1] / sr:.1f}s at {sr} Hz")

    return saved_paths

In [17]:

import gc
import json
import torch

all_saved_paths = []
manifest = []

for animal_index, animal in enumerate(animal_prompts):
    name = animal["name"]
    prompt = animal["prompt"]
    duration = animal["duration"]

    animal_dir = OUTPUT_DIR / name
    animal_dir.mkdir(parents=True, exist_ok=True)

    # Check which variations already exist
    expected_paths = [
        animal_dir / f"{name}_variation_{i:02d}.wav"
        for i in range(1, VARIATIONS_PER_PROMPT + 1)
    ]
    existing_paths = [p for p in expected_paths if p.is_file()]
    missing_paths = [p for p in expected_paths if not p.is_file()]

    print("\n" + "=" * 65)
    print(f"Animal {animal_index + 1}/{len(animal_prompts)}: {name}")
    print(f"Duration: {duration}s")
    print(f"Already saved: {len(existing_paths)}/{VARIATIONS_PER_PROMPT}")

    # Keep completed animals untouched
    if not missing_paths:
        print("All variations exist; skipping generation.")
        all_saved_paths.extend(existing_paths)
        for path in existing_paths:
            manifest.append({
                "animal": name,
                "prompt": prompt,
                "duration": duration,
                "file": str(path),
            })
        continue

    seed = BASE_SEED + animal_index * 100

    # Generate only the number of missing variations
    out = model.generate(
        prompt=prompt,
        duration=duration,
        steps=STEPS,
        seed=seed,
        batch_size=len(missing_paths),
    )

    audio, sr = unpack(out)
    audio = torch.as_tensor(audio).float().detach().cpu()

    # Normalize to (batch, channels, samples)
    if audio.dim() == 1:
        audio = audio.unsqueeze(0).unsqueeze(0)
    elif audio.dim() == 2:
        audio = audio.unsqueeze(0)

    if audio.shape[0] != len(missing_paths):
        raise RuntimeError(
            f"{name}: requested {len(missing_paths)} clips but "
            f"received {audio.shape[0]}. No files from this batch were saved."
        )

    for clip, path in zip(audio, missing_paths):
        clip = clip / clip.abs().max().clamp(min=1e-8)
        sf.write(path, clip.T.numpy(), sr)

        all_saved_paths.append(path)
        manifest.append({
            "animal": name,
            "prompt": prompt,
            "duration": duration,
            "file": str(path),
            "seed": seed,
        })

        print(f"Saved: {path.name} ({clip.shape[-1] / sr:.1f}s)")

    del out, audio
    gc.collect()
    if torch.cuda.is_available():
        torch.cuda.empty_cache()

# Rebuild the manifest from all files that now exist.
# This also preserves entries for previously completed animals.
manifest = []
for animal in animal_prompts:
    name = animal["name"]
    for i in range(1, VARIATIONS_PER_PROMPT + 1):
        path = OUTPUT_DIR / name / f"{name}_variation_{i:02d}.wav"
        if path.is_file():
            manifest.append({
                "animal": name,
                "prompt": animal["prompt"],
                "duration": animal["duration"],
                "file": str(path),
            })

manifest_path = OUTPUT_DIR / "animal_sounds_manifest.json"
with open(manifest_path, "w", encoding="utf-8") as f:
    json.dump(manifest, f, indent=2, ensure_ascii=False)

print("\nGeneration pass complete.")
print(f"Saved clips: {len(manifest)}/"
      f"{len(animal_prompts) * VARIATIONS_PER_PROMPT}")
print("Manifest:", manifest_path)



Animal 1/1: 0-jungle-ambient
Duration: 120s
Already saved: 0/3


100%|██████████| 8/8 [10:52<00:00, 81.57s/it]


Saved: 0-jungle-ambient_variation_01.wav (120.0s)
Saved: 0-jungle-ambient_variation_02.wav (120.0s)
Saved: 0-jungle-ambient_variation_03.wav (120.0s)

Generation pass complete.
Saved clips: 3/3
Manifest: /content/drive/MyDrive/FictionalAnimals/animal_sounds/animal_sounds_manifest.json


In [18]:
from IPython.display import Audio, display

for animal in animal_prompts:
    animal_dir = OUTPUT_DIR / animal["name"]
    files = sorted(animal_dir.glob("*.wav"))

    print("\n" + "=" * 60)
    print(animal["name"])
    print("Prompt:", animal["prompt"])

    for path in files:
        print(path.name)
        display(Audio(str(path)))


0-jungle-ambient
Prompt: ambient jungle soundscape
0-jungle-ambient_variation_01.wav


0-jungle-ambient_variation_02.wav


0-jungle-ambient_variation_03.wav


In [19]:
total = 0

for animal in animal_prompts:
    files = sorted((OUTPUT_DIR / animal["name"]).glob("*.wav"))
    print(f"{animal['name']}: {len(files)} files")
    total += len(files)

print(f"\nTotal: {total}/48 audio files")

assert total == 3, f"Expected 48 audio files, found {total}"
print("All audio files are present.")

0-jungle-ambient: 3 files

Total: 3/48 audio files


AssertionError: Expected 48 audio files, found 3